# Baseline Recommender 1

Full feature space: 
use all 518 audio features, scale them, then calculate nearest neighbours/cosine similarity
no PCA

In [1]:
import pandas as pd
import numpy as np

from sklearn.preprocessing import StandardScaler
from sklearn.neighbors import NearestNeighbors

In [2]:
tracks = pd.read_csv(
    "../data/raw/fma_metadata/tracks.csv",
    index_col=0,
    header=[0, 1]
)

features = pd.read_csv(
    "../data/raw/fma_metadata/features.csv",
    index_col=0,
    header=[0, 1, 2]
)

In [3]:
small_tracks = tracks[
    tracks[("set", "subset")] == "small"
].copy()

small_features = features.loc[small_tracks.index].copy()

In [4]:
small_tracks.shape


(8000, 52)

In [5]:
small_features.shape

(8000, 518)

In [6]:
small_features.isna().sum().sum()

np.int64(0)

In [7]:
small_features.dtypes.value_counts()

float64    518
Name: count, dtype: int64

In [8]:
# scale the features

scaler = StandardScaler()

X_scaled = scaler.fit_transform(small_features)

In [9]:
X_scaled.shape

(8000, 518)

In [10]:
X_scaled.mean()


np.float64(-1.0608931150985685e-16)

In [11]:
X_scaled.std()

np.float64(1.0)

In [12]:
# fit the nearest neighbour model

nn_model = NearestNeighbors(
    n_neighbors=11,
    metric="cosine",
    algorithm="brute"
)

nn_model.fit(X_scaled)

,"n_neighbors n_neighbors: int, default=5Number of neighbors to use by default for :meth:`kneighbors` queries.",11
,"algorithm algorithm: {'auto', 'ball_tree', 'kd_tree', 'brute'}, default='auto'Algorithm used to compute the nearest neighbors:- 'ball_tree' will use :class:`BallTree`- 'kd_tree' will use :class:`KDTree`- 'brute' will use a brute-force search.- 'auto' will attempt to decide the most appropriate algorithm based on the values passed to :meth:`fit` method.Note: fitting on sparse input will override the setting ofthis parameter, using brute force.",'brute'
,"metric metric: str or callable, default='minkowski'Metric to use for distance computation. Default is ""minkowski"", whichresults in the standard Euclidean distance when p = 2. See thedocumentation of `scipy.spatial.distance<https://docs.scipy.org/doc/scipy/reference/spatial.distance.html>`_ andthe metrics listed in:class:`~sklearn.metrics.pairwise.distance_metrics` for valid metricvalues.If metric is ""precomputed"", X is assumed to be a distance matrix andmust be square during fit. X may be a :term:`sparse graph`, in whichcase only ""nonzero"" elements may be considered neighbors.If metric is a callable function, it takes two arrays representing 1Dvectors as inputs and must return one value indicating the distancebetween those vectors. This works for Scipy's metrics, but is lessefficient than passing the metric name as a string.",'cosine'
,"radius radius: float, default=1.0Range of parameter space to use by default for :meth:`radius_neighbors`queries.",1.0
,"leaf_size leaf_size: int, default=30Leaf size passed to BallTree or KDTree. This can affect thespeed of the construction and query, as well as the memoryrequired to store the tree. The optimal value depends on thenature of the problem.",30
,"p p: float (positive), default=2Parameter for the Minkowski metric fromsklearn.metrics.pairwise.pairwise_distances. When p = 1, this isequivalent to using manhattan_distance (l1), and euclidean_distance(l2) for p = 2. For arbitrary p, minkowski_distance (l_p) is used.",2
,"metric_params metric_params: dict, default=NoneAdditional keyword arguments for the metric function.",None
,"n_jobs n_jobs: int, default=NoneThe number of parallel jobs to run for neighbors search.``None`` means 1 unless in a :obj:`joblib.parallel_backend` context.``-1`` means using all processors. See :term:`Glossary <n_jobs>`for more details.",None
Name,Type,Value
effective_metric_ effective_metric_: strMetric used to compute distances to neighbors.,str,'cosine'
effective_metric_params_ effective_metric_params_: dictParameters for the metric used to compute distances to neighbors.,dict,{}


In [13]:
# create a recommendation function

def recommend_similar_tracks(track_id, n=10):

    if track_id not in small_tracks.index:
        raise ValueError("Track ID not found in FMA Small.")

    position = small_tracks.index.get_loc(track_id)

    distances, indices = nn_model.kneighbors(
        X_scaled[position].reshape(1, -1),
        n_neighbors=n + 1
    )

    # Remove the track itself
    neighbour_indices = indices[0][1:]
    neighbour_distances = distances[0][1:]

    result_ids = small_tracks.index[neighbour_indices]

    results = small_tracks.loc[
        result_ids,
        [
            ("artist", "name"),
            ("track", "title"),
            ("track", "genre_top"),
        ]
    ].copy()

    # Flatten the MultiIndex columns
    results.columns = [
        "artist",
        "title",
        "genre"
    ]

    results["cosine_distance"] = neighbour_distances
    results["similarity"] = 1 - neighbour_distances

    return results

In [14]:
# try a track

small_tracks[
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top"),
    ]
].sample(20)

artist                                        track  \
                            name                                        title   
track_id                                                                        
83558                  Underling                                     carnival   
95914          Suicidal Rap Orgy                              Genital Warfare   
130988         Blue Dot Sessions                                    3rd Chair   
145887               Squire Tuck                               Facing Inwards   
105713                  Sam Moss                                        Ocean   
51272                 Work Drugs                                 Summer Blood   
87971     Sandy & Caroline Paton                             Little Brown Dog   
75371               Kellee Maize                                      In Tune   
128881               Squire Tuck                     Alone Again at Christmas   
51113               Bob Ostertag                                Shadow Pocket   
141179                Simple CUT                                         Stay   
42020               Jah Henchman                       Real Avatar  (Jamaica)   
107909               Project 5am                               The Librettist   
138410               Derek Clegg                                    Only Love   
116709            Jaan Patterson  Gnossiennes No.1 (Éric Alfred Leslie Satie)   
142552             Rony Friedman                                   Come to Me   
36998                 Exteenager                              bonsoir tiroir!   
153383          Trotski Nautique                         La Samba (en public)   
131451                 Mom Jeans                               B05 Mesh Shirt   
100479                   LOWdown                    The LOWdown (Treacherous)   

                         
              genre_top  
track_id                 
83558           Hip-Hop  
95914           Hip-Hop  
130988     Instrumental  
145887     Instrumental  
105713             Folk  
51272               Pop  
87971              Folk  
75371           Hip-Hop  
128881     Experimental  
51113      Experimental  
141179              Pop  
42020     International  
107909       Electronic  
138410             Folk  
116709     Experimental  
142552              Pop  
36998        Electronic  
153383              Pop  
131451              Pop  
100479          Hip-Hop

In [15]:
recommend_similar_tracks(140, n=5)

,artist,title,genre,cosine_distance,similarity
track_id,,,,,
44805,Monk Turner + Fascinoma,Start Again,Pop,0.450473,0.549527
6803,Watcha Clan,Balkan Qoulou,International,0.480359,0.519641
77564,Bryyn,Abba Ingee,Pop,0.482405,0.517595
110451,Papascandy,Linton,International,0.493989,0.506011
52953,Marissa Nadler,Your Heart Is A Twisted Vine,Folk,0.507851,0.492149


In [16]:
# basic evaluation metric
# Of its 10 nearest neighbours, what proportion have the same genre_top

def genre_agreement_at_k(X, tracks_df, k=10):
    model = NearestNeighbors(
        n_neighbors=k + 1,
        metric="cosine",
        algorithm="brute"
    )
    
    model.fit(X)

    _, indices = model.kneighbors(X)

    genres = tracks_df[("track", "genre_top")].to_numpy()

    scores = []

    for i in range(len(tracks_df)):
        if pd.isna(genres[i]):
            continue

        neighbour_idx = indices[i][1:]
        neighbour_genres = genres[neighbour_idx]

        valid = ~pd.isna(neighbour_genres)

        if valid.sum() == 0:
            continue

        score = (
            neighbour_genres[valid] == genres[i]
        ).mean()

        scores.append(score)

    return np.mean(scores)

In [17]:
baseline_genre_agreement = genre_agreement_at_k(
    X_scaled,
    small_tracks,
    k=10
)

baseline_genre_agreement

np.float64(0.41415)

In [18]:
import time

start = time.time()

_ = nn_model.kneighbors(X_scaled[:100])

elapsed = time.time() - start

print(f"100 queries took {elapsed:.4f} seconds")

100 queries took 0.0163 seconds


## Baseline 1 — Full audio feature space

- Dataset: FMA Small
- Tracks: 8,000
- Audio features: 518
- Scaling: StandardScaler
- Similarity metric: Cosine distance
- Model: NearestNeighbors
- Genre agreement@10: 0.4142
- Query time: 0.0437 seconds for 100 queries

The full audio feature space produces neighbourhoods substantially
more coherent than random genre assignment (0.125 baseline).
Recommendations can cross top-level genres, suggesting that the
audio features capture relationships not represented by coarse genre labels.

The standardized feature matrix has mean ≈ 0 and standard deviation = 1,
confirming correct scaling. The baseline produces neighbourhoods substantially more coherent than random assignment across 8 balanced genres.

Note, that when testing the recommender, 2x tracks by Monk Turner appeared. This would obviously skew the results with a sense of similarity. Will include a same-artist-excluded evaluation later.

# Qualitative baseline check

This will test the model manually, looking at a number of tracks recommended and listening manually to evaluate similarity 

I will carry out this test on each other proceeding Baseline models (PCA 146 and PCA 60), running the same seed tracks through these models to ask:
Did PCA change the actual recommendations, and do they still sound equally coherent?

One especially useful test is to flag recommendations as:

obvious similarity
interesting cross-genre similarity
doesn't make musical sense

Those “interesting cross-genre” cases are particularly valuable, because that's eventually where TasteBridge wants to operate.

We don't need a rigorous user study yet. 10 seeds × 3–5 recommendations is plenty for this baseline sanity check. Then keep those same seed tracks as a fixed qualitative benchmark throughout the modelling process.

In [19]:
small_tracks[
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top")
    ]
].sample(30, random_state=42)

artist  \
                                                name   
track_id                                               
54033                                  alright lover   
59876                                     Boy Friend   
42234                  Zlatne Uste Balkan Brass Band   
68893                                 Broke For Free   
97544                                      Amitron_7   
62191                                         Divans   
43883                                            Myo   
27610                            El Niño del Parking   
90826                                    The Mantles   
84605                                    EARTH-ENEMY   
39318     John Badger & The Moustache Riders of Doom   
67363                                  Directorsound   
68537                                    andybrannan   
96408                                 Mário Gajarský   
97542                                      Amitron_7   
98567                                         Hi-Rez   
149701                                           Sro   
110209                                 Circus Marcus   
63471                               Mutilation Rites   
55232                                  Mastermind XS   
87188                                  Eric & Magill   
122143              Anthony Donovan & Jaan Patterson   
123978                               BenJamin Banger   
143306                             Chase Alan Willis   
17608                                 Alash Ensemble   
71247                                         Dengaz   
149700                                           Sro   
71508                                            egr   
16339                                        Twizzle   
69747                               Manueljgrotesque   

                                                 track                 
                                                 title      genre_top  
track_id                                                               
54033                                        Snow Wave            Pop  
59876                                      Lovedropper           Rock  
42234                                      Lacin Cocek  International  
68893                                   Sidewalk Chalk     Electronic  
97544                      Escape Under Cover of Night     Electronic  
62191                                      Go digitale  International  
43883                                         crickets   Experimental  
27610                          Big Foot (Cuántos Años)  International  
90826                                     Reason's Run            Pop  
84605                                Me and My Friends            Pop  
39318             A Dream of Heaven in a Terminal Ward   Experimental  
67363                                 Before The March            Pop  
68537     Ambience Brooklyn Zoo Kids Waiting for Train   Experimental  
96408                                   Fucking Desire           Rock  
97542                                     Lotus Flower     Electronic  
98567                                   Fuck The World        Hip-Hop  
149701                                     Answering M     Electronic  
110209                             La tapa del viernes   Experimental  
63471                                          Goliath           Rock  
55232                                Stop That Mission  International  
87188                              Grandpa's Pink Wine            Pop  
122143                           Genome Chomsky (pt I)   Experimental  
123978                          Fuck Yall, Im Goin Pop        Hip-Hop  
143306                                 Take Your Pills   Instrumental  
17608                                        Bai-Taiga  International  
71247                                         Imortais        Hip-Hop  
149700                                    Rising Heart     Electronic  
71508                          Burn D

In [20]:
#
test_track_ids = [
    140,
    54033,
    59876,
    42234,
    68893,
    43883,
    98567,
    149701,
    63471,
    17608
]

In [21]:
[id_ for id_ in test_track_ids if id_ not in small_tracks.index]

[]

In [22]:
small_tracks.loc[
    test_track_ids,
    [
        ("artist", "name"),
        ("track", "title"),
        ("track", "genre_top")
    ]
]

artist               track               
                                     name               title      genre_top
track_id                                                                    
140       Alec K. Redfearn & the Eyesores  Queen Of The Wires           Folk
54033                       alright lover           Snow Wave            Pop
59876                          Boy Friend         Lovedropper           Rock
42234       Zlatne Uste Balkan Brass Band         Lacin Cocek  International
68893                      Broke For Free      Sidewalk Chalk     Electronic
43883                                 Myo            crickets   Experimental
98567                              Hi-Rez      Fuck The World        Hip-Hop
149701                                Sro         Answering M     Electronic
63471                    Mutilation Rites             Goliath           Rock
17608                      Alash Ensemble           Bai-Taiga  International

In [23]:
#Generate 5 recommendations for each seed

evaluation_rows = []

for seed_id in test_track_ids:

    seed = small_tracks.loc[seed_id]

    recommendations = recommend_similar_tracks(
        seed_id,
        n=5
    )

    for rec_id, rec in recommendations.iterrows():

        evaluation_rows.append({
            "seed_track_id": seed_id,
            "seed_artist": seed[("artist", "name")],
            "seed_title": seed[("track", "title")],
            "seed_genre": seed[("track", "genre_top")],

            "recommended_track_id": rec_id,
            "recommended_artist": rec["artist"],
            "recommended_title": rec["title"],
            "recommended_genre": rec["genre"],

            "cosine_similarity": rec["similarity"],

            "manual_similarity_1_5": np.nan,
            "connection_type": "",
            "notes": ""
        })

In [ ]:
#Turn it into a table
manual_eval = pd.DataFrame(evaluation_rows)

manual_eval.head(10)

,seed_track_id,seed_artist,seed_title,seed_genre,recommended_track_id,recommended_artist,recommended_title,recommended_genre,cosine_similarity,manual_similarity_1_5,connection_type,notes
0,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,44805,Monk Turner + Fascinoma,Start Again,Pop,0.549527,NaN,,
1,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,6803,Watcha Clan,Balkan Qoulou,International,0.519641,NaN,,
2,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,77564,Bryyn,Abba Ingee,Pop,0.517595,NaN,,
3,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,110451,Papascandy,Linton,International,0.506011,NaN,,
4,140,Alec K. Redfearn & the Eyesores,Queen Of The Wires,Folk,52953,Marissa Nadler,Your Heart Is A Twisted Vine,Folk,0.492149,NaN,,
5,54033,alright lover,Snow Wave,Pop,145556,This Mess is Mine,Roommates (Piano Version by AGPB),Folk,0.500335,NaN,,
6,54033,alright lover,Snow Wave,Pop,63456,Big Blood,Away pt. II,Folk,0.453994,NaN,,
7,54033,alright lover,Snow Wave,Pop,14571,Ergo Phizmiz,Through the Doors of the Circus,Instrumental,0.441940,NaN,,
8,54033,alright lover,Snow Wave,Pop,114070,Blue Dot Sessions,Grand Fell,Instrumental,0.430511,NaN,,
9,54033,alright lover,Snow Wave,Pop,134388,Scott Holmes,Magical Moments,Pop,0.427252,NaN,,


In [ ]:
#verifying the shape of the manual evaluation table
manual_eval.shape

(50, 12)

In [ ]:
#verifying the data types in the manual evaluation table
manual_eval.dtypes

seed_track_id              int64
seed_artist                  str
seed_title                   str
seed_genre                   str
recommended_track_id       int64
recommended_artist           str
recommended_title            str
recommended_genre            str
cosine_similarity        float64
manual_similarity_1_5    float64
connection_type              str
notes                        str
dtype: object

In [ ]:
#save the recommendations for carrying out assessment
manual_eval.to_csv(
    "../data/processed/baseline1_manual_evaluation.csv",
    index=False
)

# Listen to tracks directly in this notebook

Scores get added to the relevant .csv for a machine vs human comparison

similarity_score:

1 = sounds unrelated

2 = weak connection

3 = some clear similarity

4 = strongly related

5 = very similar


connection_type:

rhythm

timbre

mood

instrumentation

energy

production (maybe less relevant)

harmony

vocals

cross-genre

unclear

### Guidance for Rating

Similarity rating

Use a 1–5 scale.

Score	Meaning
1	No meaningful musical similarity. The recommendation feels unrelated.
2	Weak similarity. One or two minor characteristics may connect them, but overall they sound quite different.
3	Moderate similarity. There is a recognisable musical connection, although there are also substantial differences.
4	Strong similarity. Several important musical characteristics clearly connect the tracks.
5	Very strong similarity. The tracks are highly alike in sound, structure, atmosphere or production.

Example ratings

A 4 might be:

Similar percussion, tempo and atmosphere, despite different genres.

A 3 might be:

Similar vocal style and mood, but instrumentation and rhythm are quite different.

A 2 might be:

Both are acoustic, but otherwise the connection is weak.

A 1 might be:

Different tempo, instrumentation, mood and production; no obvious connection.

Listening procedure

For consistency, listen to roughly the same amount of each track. Around 20–30 seconds is enough initially, but listen longer when the relationship is unclear.

Listen to the seed first, then the recommendation.

Try not to look at the cosine similarity before deciding your score if possible. We do not want the model's score to influence the human judgement.

In [28]:
from IPython.display import Audio, display
from pathlib import Path

In [29]:
def get_fma_audio_path(track_id):
    track_id_str = f"{track_id:06d}"
    
    return (
        Path("../data/raw/fma_small")
        / track_id_str[:3]
        / f"{track_id_str}.mp3"
    )

In [30]:
get_fma_audio_path(140)

PosixPath('../data/raw/fma_small/000/000140.mp3')

In [31]:
def listen_to_pair(seed_id, rec_id):
    print("SEED")
    print(
        small_tracks.loc[
            seed_id,
            [("artist", "name"), ("track", "title")]
        ]
    )
    display(Audio(get_fma_audio_path(seed_id)))

    print("\nRECOMMENDATION")
    print(
        small_tracks.loc[
            rec_id,
            [("artist", "name"), ("track", "title")]
        ]
    )
    display(Audio(get_fma_audio_path(rec_id)))

In [32]:
listen_to_pair(140, 44805)
# similarity_score = 3
# connection_type = mood, energy, production, harmony 

SEED
artist  name     Alec K. Redfearn & the Eyesores
track   title                 Queen Of The Wires
Name: 140, dtype: str



RECOMMENDATION
artist  name     Monk Turner + Fascinoma
track   title                Start Again
Name: 44805, dtype: str


In [33]:
listen_to_pair(140, 6803)
# similarity_score = 2
# connection_type = harmony, unclear, cross-genre
# weaker connection but still signs of belonging (if playlisted)

SEED
artist  name     Alec K. Redfearn & the Eyesores
track   title                 Queen Of The Wires
Name: 140, dtype: str



RECOMMENDATION
artist  name       Watcha Clan
track   title    Balkan Qoulou
Name: 6803, dtype: str


In [34]:
listen_to_pair(140, 77564)
# similarity_score = 4
# connection_type = mood, energy, harmony, vocals
# clear signs of belonging in a similar playlist


SEED
artist  name     Alec K. Redfearn & the Eyesores
track   title                 Queen Of The Wires
Name: 140, dtype: str



RECOMMENDATION
artist  name          Bryyn
track   title    Abba Ingee
Name: 77564, dtype: str


In [35]:
listen_to_pair(140, 110451)
# similarity_score = 2
# connection_type = mood, unclear, cross-genre
# weaker connection but clear signs of belonging in a similar playlist

SEED
artist  name     Alec K. Redfearn & the Eyesores
track   title                 Queen Of The Wires
Name: 140, dtype: str



RECOMMENDATION
artist  name     Papascandy
track   title        Linton
Name: 110451, dtype: str


In [ ]:
listen_to_pair(140, 52953)
# similarity_score = 4
# connection_type = energy, mood, vocals, production
# strong connection and would put in a similar playlist

SEED
artist  name     Alec K. Redfearn & the Eyesores
track   title                 Queen Of The Wires
Name: 140, dtype: str



RECOMMENDATION
artist  name                   Marissa Nadler
track   title    Your Heart Is A Twisted Vine
Name: 52953, dtype: str


In [ ]:
listen_to_pair(54033, 145556)
# similarity_score = 5
# connection_type = energy, mood, production
# strong connection and would put in a similar playlist

SEED
artist  name     alright lover
track   title        Snow Wave
Name: 54033, dtype: str



RECOMMENDATION
artist  name                     This Mess is Mine
track   title    Roommates (Piano Version by AGPB)
Name: 145556, dtype: str


In [ ]:
listen_to_pair(54033, 63456)
# similarity_score = 5
# connection_type = rhythm, energy, mood, production, instrumentation
# strong connection and would put in a similar playlist

SEED
artist  name     alright lover
track   title        Snow Wave
Name: 54033, dtype: str



RECOMMENDATION
artist  name       Big Blood
track   title    Away pt. II
Name: 63456, dtype: str


In [ ]:
listen_to_pair(54033, 14571)
# similarity_score = 2
# connection_type = 
# weaker connection but would put in a similar playlist as not distant energetically

SEED
artist  name     alright lover
track   title        Snow Wave
Name: 54033, dtype: str



RECOMMENDATION
artist  name                        Ergo Phizmiz
track   title    Through the Doors of the Circus
Name: 14571, dtype: str


In [ ]:
listen_to_pair(54033, 114070)
# similarity_score = 3
# connection_type = mood
# medium connection. Would put in a similar playlist

SEED
artist  name     alright lover
track   title        Snow Wave
Name: 54033, dtype: str



RECOMMENDATION
artist  name     Blue Dot Sessions
track   title           Grand Fell
Name: 114070, dtype: str


In [ ]:
listen_to_pair(54033, 134388)
# similarity_score = 2
# connection_type = unclear
# weaker connection. maybe would put in a similar playlist, similar energy

SEED
artist  name     alright lover
track   title        Snow Wave
Name: 54033, dtype: str



RECOMMENDATION
artist  name        Scott Holmes
track   title    Magical Moments
Name: 134388, dtype: str
